# Visualizing Cloud Fraction Uncertainties with Altair and Plotly

This notebook is one of three notebooks that serve to show how the ESA CCI Toolbox can be used with D3.js. Here, we will show how uncertainties included in a CCI Cloud Dataset can be visualised using charts from Altair and Plotly. Several preprocessing steps are applied, partly using operations from the CCI Toolbox.

Install altair and plotly it into your Python environment if you haven't already done so:

In [1]:
# ! mamba install --yes altair plotly

Again, we first take care of our necessary imports:

In [2]:
import altair as alt
import matplotlib.pyplot as plt
%matplotlib inline
import numpy as np
import pandas as pd
import plotly.graph_objects as go

from esa_climate_toolbox.core import get_op
from esa_climate_toolbox.core import list_ecv_datasets
from esa_climate_toolbox.core import open_data

For this notebook, we want to look at a Cloud CCI dataset, so first we see what the toolbox has to offer here. For more information on Ozone Data, see here: https://climate.esa.int/en/projects/cloud/.

In [3]:
list_ecv_datasets(ecv="CLOUD")

[('esacci.CLOUD.mon.L3C.CLD_PRODUCTS.MODIS.Aqua.MODIS_AQUA.2-0.r1', 'esa-cci'),
 ('esacci.CLOUD.mon.L3C.CLD_PRODUCTS.MODIS.Terra.MODIS_TERRA.2-0.r1',
  'esa-cci'),
 ('esacci.CLOUD.mon.L3C.CLD_PRODUCTS.multi-sensor.multi-platform.ATSR2-AATSR.3-0.r1',
  'esa-cci'),
 ('esacci.CLOUD.mon.L3C.CLD_PRODUCTS.multi-sensor.multi-platform.AVHRR-AM.3-0.r1',
  'esa-cci'),
 ('esacci.CLOUD.mon.L3C.CLD_PRODUCTS.multi-sensor.multi-platform.AVHRR-PM.3-0.r1',
  'esa-cci'),
 ('esacci.CLOUD.mon.L3C.CLD_PRODUCTS.multi-sensor.multi-platform.MERIS-AATSR.2-0.r1',
  'esa-cci'),
 ('ESACCI-L3C_CLOUD-CLD_PRODUCTS-MODIS_AQUA-200208-201412-fv2.0_kr1.0',
  'esa-cci-kc'),
 ('ESACCI-L3C_CLOUD-CLD_PRODUCTS-ATSR2_AATSR-199506-201204-fv3.0-kr1.1',
  'esa-cci-kc'),
 ('ESACCI-L3C_CLOUD-CLD_PRODUCTS-AVHRR_AM-199109-201612-fv3.0-kr1.1',
  'esa-cci-kc'),
 ('ESACCI-L3C_CLOUD-CLD_PRODUCTS-AVHRR_PM-198201-201612-fv3.0-kr1.1',
  'esa-cci-kc'),
 ('ESACCI-L3C_CLOUD-CLD_PRODUCTS-MERIS-AATSR_ENVISAT-200301-201112_fv2.0_kr1.0',
  'esa-c

There is a zarr dataset covering data from 1982 to 2016, so we will continue with this. We open it using the toolbox' `open_data` function.

In [4]:
cloud_ds, _ = open_data("ESACCI-L3C_CLOUD-CLD_PRODUCTS-AVHRR_NOAA-1982-2016-fv3.0.zarr", data_store_id="esa-cci-zarr")
cloud_ds

<xarray.Dataset> Size: 6GB
Dimensions:   (time: 415, lat: 360, lon: 720)
Coordinates:
  * lat       (lat) float32 1kB -89.75 -89.25 -88.75 ... 88.75 89.25 89.75
  * lon       (lon) float32 3kB -179.8 -179.2 -178.8 ... 178.8 179.2 179.8
  * time      (time) datetime64[ns] 3kB 1982-01-01 1982-02-01 ... 2016-12-01
Data variables:
    cfc       (time, lat, lon) float64 861MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_high  (time, lat, lon) float64 861MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_low   (time, lat, lon) float64 861MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_mid   (time, lat, lon) float64 861MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_std   (time, lat, lon) float64 861MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_unc   (time, lat, lon) float64 861MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    nobs      (time, lat, lon) float64 861MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
Attributes: (12/40)
    Conventions:                 CF-1.6,ACDD-1.3
    cdm_data_type:               Grid
    comment:                     These data were produced at ESACCI as part o...
    creator_email:               contact.cloudcci@dwd.de
    creator_name:                Deutscher Wetterdienst
    creator_url:                 http://www.dwd.de
    ...                          ...
    time_coverage_duration:      P1M
    time_coverage_end:           20161231T235959Z
    time_coverage_resolution:    P1M
    time_coverage_start:         20161201T000000Z
    title:                       ESA Cloud CCI Retrieval Products L3 Output File
    tracking_id:                 dc09abb8-324f-4cc6-97f1-d8c0e4deae2e

We see that it has a variable `cfc` which represents the cloud fraction. It comes also with several describin bands, such as bands describing the standard deviation and the uncertainty. This is perfect for our case.
Now, we want to only look at the last 4 years, so we create a temporal subset using the `subset_temporal_index` operation.

In [5]:
subset_time_index = get_op("subset_temporal_index")
cloud_ds = subset_time_index(cloud_ds, 367, 415)
cloud_ds

<xarray.Dataset> Size: 697MB
Dimensions:   (time: 48, lat: 360, lon: 720)
Coordinates:
  * lat       (lat) float32 1kB -89.75 -89.25 -88.75 ... 88.75 89.25 89.75
  * lon       (lon) float32 3kB -179.8 -179.2 -178.8 ... 178.8 179.2 179.8
  * time      (time) datetime64[ns] 384B 2013-01-01 2013-02-01 ... 2016-12-01
Data variables:
    cfc       (time, lat, lon) float64 100MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_high  (time, lat, lon) float64 100MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_low   (time, lat, lon) float64 100MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_mid   (time, lat, lon) float64 100MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_std   (time, lat, lon) float64 100MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_unc   (time, lat, lon) float64 100MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    nobs      (time, lat, lon) float64 100MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
Attributes: (12/40)
    Conventions:                 CF-1.6,ACDD-1.3
    cdm_data_type:               Grid
    comment:                     These data were produced at ESACCI as part o...
    creator_email:               contact.cloudcci@dwd.de
    creator_name:                Deutscher Wetterdienst
    creator_url:                 http://www.dwd.de
    ...                          ...
    time_coverage_duration:      P1M
    time_coverage_end:           20161231T235959Z
    time_coverage_resolution:    P1M
    time_coverage_start:         20161201T000000Z
    title:                       ESA Cloud CCI Retrieval Products L3 Output File
    tracking_id:                 dc09abb8-324f-4cc6-97f1-d8c0e4deae2e

In the next step, we create a time series for a single point. We pick coordinate pointing at Hamburg, Germany.

In [6]:
tpoint = get_op("tseries_point")
cloud_point_ts = tpoint(cloud_ds, point="10, 53.5")
cloud_point_ts

<xarray.Dataset> Size: 3kB
Dimensions:   (time: 48)
Coordinates:
    lat       float32 4B 53.75
    lon       float32 4B 10.25
  * time      (time) datetime64[ns] 384B 2013-01-01 2013-02-01 ... 2016-12-01
Data variables:
    cfc       (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_high  (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_low   (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_mid   (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_std   (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_unc   (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    nobs      (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
Attributes: (12/34)
    Conventions:                 CF-1.6,ACDD-1.3
    cdm_data_type:               Grid
    comment:                     These data were produced at ESACCI as part o...
    creator_email:               contact.cloudcci@dwd.de
    creator_name:                Deutscher Wetterdienst
    creator_url:                 http://www.dwd.de
    ...                          ...
    time_coverage_duration:      P1M
    time_coverage_end:           20161231T235959Z
    time_coverage_resolution:    P1M
    time_coverage_start:         20161201T000000Z
    title:                       ESA Cloud CCI Retrieval Products L3 Output File
    tracking_id:                 dc09abb8-324f-4cc6-97f1-d8c0e4deae2e

We receive a dataset that has only one value for `lat` and `lon`. This dataset can easily be converted into a dataframe, which will serve as input for the further visualisation. We use the `to_dataframe` function from the toolbox.

In [7]:
df_op = get_op("to_dataframe")
cloud_point_df = df_op(ds=cloud_point_ts)
cloud_point_df

,cfc,cfc_high,cfc_low,cfc_mid,cfc_std,cfc_unc,lat,lon,nobs
time,,,,,,,,,
2013-01-01,0.960013,0.151986,0.503206,0.304534,0.195928,5.221246,53.75,10.25,8953.0
2013-02-01,0.862689,0.053956,0.620685,0.187414,0.344175,6.221479,53.75,10.25,8062.0
2013-03-01,0.700607,0.085563,0.399707,0.214020,0.457992,10.280500,53.75,10.25,8898.0
2013-04-01,0.673349,0.071621,0.336838,0.262180,0.468988,11.991373,53.75,10.25,8630.0
2013-05-01,0.785906,0.110165,0.335201,0.339796,0.410193,9.807740,53.75,10.25,8954.0
2013-06-01,0.704416,0.176729,0.348814,0.177463,0.456305,14.936710,53.75,10.25,8221.0
2013-07-01,0.539337,0.130200,0.287160,0.118507,0.498450,19.104975,53.75,10.25,8961.0
2013-08-01,0.719286,0.154674,0.324306,0.237507,0.449348,15.842041,53.75,10.25,8913.0
2013-09-01,0.729208,0.098663,0.353824,0.275927,0.444369,11.641881,53.75,10.25,8549.0


This method has automatically set the time as the dataframe index. This prevents time from being represented as a column, this making it unusable by Altair. As we don't want this, we reset the index.

In [8]:
cloud_point_df = cloud_point_df.reset_index().rename(columns={'index': 'timestamp'})
cloud_point_df

,time,cfc,cfc_high,cfc_low,cfc_mid,cfc_std,cfc_unc,lat,lon,nobs
0,2013-01-01,0.960013,0.151986,0.503206,0.304534,0.195928,5.221246,53.75,10.25,8953.0
1,2013-02-01,0.862689,0.053956,0.620685,0.187414,0.344175,6.221479,53.75,10.25,8062.0
2,2013-03-01,0.700607,0.085563,0.399707,0.214020,0.457992,10.280500,53.75,10.25,8898.0
3,2013-04-01,0.673349,0.071621,0.336838,0.262180,0.468988,11.991373,53.75,10.25,8630.0
4,2013-05-01,0.785906,0.110165,0.335201,0.339796,0.410193,9.807740,53.75,10.25,8954.0
5,2013-06-01,0.704416,0.176729,0.348814,0.177463,0.456305,14.936710,53.75,10.25,8221.0
6,2013-07-01,0.539337,0.130200,0.287160,0.118507,0.498450,19.104975,53.75,10.25,8961.0
7,2013-08-01,0.719286,0.154674,0.324306,0.237507,0.449348,15.842041,53.75,10.25,8913.0
8,2013-09-01,0.729208,0.098663,0.353824,0.275927,0.444369,11.641881,53.75,10.25,8549.0
9,2013-10-01,0.767853,0.298940,0.283040,0.184145,0.422202,11.038484,53.75,10.25,8934.0


Now, the dataframe is ready to be used. We start with plotting a simple line using the Altair library. As we will use this later, we wrap it into a function. In the plot, the x-axis shows the time and the y-axis shows the cloud fraction.

In [9]:
def create_line(cloud_df: pd.DataFrame, color: str = "blue"):
    return alt.Chart(cloud_df).mark_point(color=color).encode(
        x='time:T',
        y='cfc:Q'
    )

In [10]:
line = create_line(cloud_point_df)
line

alt.Chart(...)

Now, we can add the uncertainty values, which are encoded in the `cfc_unc` variable. We display these as a semi-transparent area, where the uncertainty values define top and bottom values around the cfc value. As the uncertainty is given in percent, we also need to divide it by 100.

In [11]:
def create_band(cloud_df: pd.DataFrame, color: str = "blue"):
    return alt.Chart(cloud_df).mark_area(color=color, opacity=0.3).encode(
        x='time:T',
        y='y1:Q',
        y2='y2:Q'
    ).transform_calculate(
        y1="datum.cfc - (datum.cfc_unc / 100 / 2)",
        y2="datum.cfc + (datum.cfc_unc / 100 / 2)"
    )

In [12]:
band = create_band(cloud_point_df)

line + band

alt.LayerChart(...)

Alternatively, we can create bars to display variation. Here, we use the standard deviation band instead.

In [13]:
def create_bars(cloud_df: pd.DataFrame):
    return alt.Chart(cloud_df).mark_rule().encode(
        x='time:T',
        y='cfc:Q',
        y2=alt.Y('y_uncertainty:Q', scale=alt.Scale(zero=False), title="Uncertainty")
    ).transform_calculate(
        y2="datum.cfc + (datum.cfc_std / 2)",
        y1="datum.cfc - (datum.cfc_std / 2)"
    ).encode(
        y='y1:Q',
        y2='y2:Q'
    )

In [14]:
bars = create_bars(cloud_point_df)

line + bars

alt.LayerChart(...)

We may create such plots for another location, this time one in the Sahara desert ...

In [15]:
cloud_point_2_ts = tpoint(cloud_ds, point="20, 25")
cloud_point_2_df = df_op(ds=cloud_point_2_ts)
cloud_point_2_df = cloud_point_2_df.reset_index().rename(columns={'index': 'timestamp'})
line_2 = create_line(cloud_point_2_df, color="red")
band_2 = create_band(cloud_point_2_df, color="red")

line_2 + band_2

alt.LayerChart(...)

... or one in the Amazon rain forest.

In [16]:
cloud_point_3_ts = tpoint(cloud_ds, point="-60, -10")
cloud_point_3_df = df_op(ds=cloud_point_3_ts)
cloud_point_3_df = cloud_point_3_df.reset_index().rename(columns={'index': 'timestamp'})
line_3 = create_line(cloud_point_3_df, color="green")
band_3 = create_band(cloud_point_3_df, color="green")

line_3 + band_3

alt.LayerChart(...)

Ultimately, we can display all plots together.

In [17]:
line + band + line_2 + band_2 + line_3 + band_3

alt.LayerChart(...)

Now, this works nicely for this dataset as it already has information on uncertainties and standard deviations. However, many CCI datasets don't. In case you still want to get a number on this, you can create another time series, where you don't get the value for a certain point, but the mean for a region, including the standard deviation. You may select suffixes for the means and standard deviations. In the case of the cloud datasets, this is necessary in order to avoid confusing the operation with the preexisting bands.

In [18]:
tmean = get_op("tseries_mean")

In [19]:
cloud_mean_ts = tmean(cloud_ds, std_suffix="_stddev")
cloud_mean_ts

cfc
cfc_high
cfc_low
cfc_mid
cfc_std
cfc_unc
nobs


<xarray.Dataset> Size: 10kB
Dimensions:          (lat: 360, lon: 720, time: 48)
Coordinates:
  * lat              (lat) float32 1kB -89.75 -89.25 -88.75 ... 89.25 89.75
  * lon              (lon) float32 3kB -179.8 -179.2 -178.8 ... 179.2 179.8
  * time             (time) datetime64[ns] 384B 2013-01-01 ... 2016-12-01
Data variables: (12/14)
    cfc_mean         (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_stddev       (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_high_mean    (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_high_stddev  (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_low_mean     (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_low_stddev   (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    ...               ...
    cfc_std_mean     (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_std_stddev   (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_unc_mean     (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    cfc_unc_stddev   (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    nobs_mean        (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
    nobs_stddev      (time) float64 384B dask.array<chunksize=(1,), meta=np.ndarray>
Attributes: (12/40)
    Conventions:                 CF-1.6,ACDD-1.3
    cdm_data_type:               Grid
    comment:                     These data were produced at ESACCI as part o...
    creator_email:               contact.cloudcci@dwd.de
    creator_name:                Deutscher Wetterdienst
    creator_url:                 http://www.dwd.de
    ...                          ...
    time_coverage_duration:      P1M
    time_coverage_end:           20161231T235959Z
    time_coverage_resolution:    P1M
    time_coverage_start:         20161201T000000Z
    title:                       ESA Cloud CCI Retrieval Products L3 Output File
    tracking_id:                 dc09abb8-324f-4cc6-97f1-d8c0e4deae2e

Now, we consider a different case. Previously, we had a look at the uncertainty distribution over time for a single point. Here, we want to got the opposite approach, where we show the spatial distribution of uncertainty for one point in time. We do this using the plotly library. 

First, we select a time step. For this, we use the `subset_temporal_index` operation from the toolbox to use the latest timestep from the original cloud dataset.

In [20]:
subset_time_index = get_op("subset_temporal_index")
sub_cloud_ds = subset_time_index(cloud_ds, 47, 48)
sub_cloud_ds

<xarray.Dataset> Size: 15MB
Dimensions:   (time: 1, lat: 360, lon: 720)
Coordinates:
  * lat       (lat) float32 1kB -89.75 -89.25 -88.75 ... 88.75 89.25 89.75
  * lon       (lon) float32 3kB -179.8 -179.2 -178.8 ... 178.8 179.2 179.8
  * time      (time) datetime64[ns] 8B 2016-12-01
Data variables:
    cfc       (time, lat, lon) float64 2MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_high  (time, lat, lon) float64 2MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_low   (time, lat, lon) float64 2MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_mid   (time, lat, lon) float64 2MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_std   (time, lat, lon) float64 2MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    cfc_unc   (time, lat, lon) float64 2MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
    nobs      (time, lat, lon) float64 2MB dask.array<chunksize=(1, 360, 720), meta=np.ndarray>
Attributes: (12/40)
    Conventions:                 CF-1.6,ACDD-1.3
    cdm_data_type:               Grid
    comment:                     These data were produced at ESACCI as part o...
    creator_email:               contact.cloudcci@dwd.de
    creator_name:                Deutscher Wetterdienst
    creator_url:                 http://www.dwd.de
    ...                          ...
    time_coverage_duration:      P1M
    time_coverage_end:           20161231T235959Z
    time_coverage_resolution:    P1M
    time_coverage_start:         20161201T000000Z
    title:                       ESA Cloud CCI Retrieval Products L3 Output File
    tracking_id:                 dc09abb8-324f-4cc6-97f1-d8c0e4deae2e

We receive a dataset with a single time step. As now we can neglect the time dimension, we do so by removing it.

In [21]:
sub_cloud_ds = sub_cloud_ds.squeeze()
sub_cloud_ds

<xarray.Dataset> Size: 15MB
Dimensions:   (lat: 360, lon: 720)
Coordinates:
  * lat       (lat) float32 1kB -89.75 -89.25 -88.75 ... 88.75 89.25 89.75
  * lon       (lon) float32 3kB -179.8 -179.2 -178.8 ... 178.8 179.2 179.8
    time      datetime64[ns] 8B 2016-12-01
Data variables:
    cfc       (lat, lon) float64 2MB dask.array<chunksize=(360, 720), meta=np.ndarray>
    cfc_high  (lat, lon) float64 2MB dask.array<chunksize=(360, 720), meta=np.ndarray>
    cfc_low   (lat, lon) float64 2MB dask.array<chunksize=(360, 720), meta=np.ndarray>
    cfc_mid   (lat, lon) float64 2MB dask.array<chunksize=(360, 720), meta=np.ndarray>
    cfc_std   (lat, lon) float64 2MB dask.array<chunksize=(360, 720), meta=np.ndarray>
    cfc_unc   (lat, lon) float64 2MB dask.array<chunksize=(360, 720), meta=np.ndarray>
    nobs      (lat, lon) float64 2MB dask.array<chunksize=(360, 720), meta=np.ndarray>
Attributes: (12/40)
    Conventions:                 CF-1.6,ACDD-1.3
    cdm_data_type:               Grid
    comment:                     These data were produced at ESACCI as part o...
    creator_email:               contact.cloudcci@dwd.de
    creator_name:                Deutscher Wetterdienst
    creator_url:                 http://www.dwd.de
    ...                          ...
    time_coverage_duration:      P1M
    time_coverage_end:           20161231T235959Z
    time_coverage_resolution:    P1M
    time_coverage_start:         20161201T000000Z
    title:                       ESA Cloud CCI Retrieval Products L3 Output File
    tracking_id:                 dc09abb8-324f-4cc6-97f1-d8c0e4deae2e

Next we convert the dataset to a dataframe.

In [22]:
cloud_df = df_op(sub_cloud_ds)
cloud_df

cfc  cfc_high   cfc_low   cfc_mid   cfc_std    cfc_unc  \
lat    lon                                                                    
-89.75 -179.75  0.666667  0.013072  0.000000  0.653595  0.471404  23.430389   
       -179.25  0.650000  0.014286  0.000000  0.635714  0.476970  24.622355   
       -178.75  0.742690  0.000000  0.000000  0.741176  0.437152  22.567369   
       -178.25  0.729560  0.000000  0.000000  0.729560  0.444187  21.117802   
       -177.75  0.696429  0.005952  0.000000  0.690476  0.459800  23.981190   
...                  ...       ...       ...       ...       ...        ...   
 89.75  177.75  0.675676  0.007519  0.315789  0.315789  0.468122  17.455336   
        178.25  0.674157  0.006135  0.306748  0.331288  0.468689  18.042696   
        178.75  0.625000  0.006579  0.315789  0.282895  0.484123  18.163563   
        179.25  0.575342  0.014388  0.302158  0.237410  0.494291  19.166298   
        179.75  0.642857  0.014085  0.260563  0.338028  0.479157  19.076298   

                 nobs       time  
lat    lon                        
-89.75 -179.75  153.0 2016-12-01  
       -179.25  140.0 2016-12-01  
       -178.75  171.0 2016-12-01  
       -178.25  159.0 2016-12-01  
       -177.75  168.0 2016-12-01  
...               ...        ...  
 89.75  177.75  148.0 2016-12-01  
        178.25  178.0 2016-12-01  
        178.75  160.0 2016-12-01  
        179.25  146.0 2016-12-01  
        179.75  154.0 2016-12-01  

[259200 rows x 8 columns]

The resulting dataframe has a multi-index consisting of combinations of lat and lon. This is not a good input for us, as we want a table like view on the data. We therefore unstack the dataframe, effectively creating matrices of latitude and longitude values per data variable.

In [23]:
cloud_df = cloud_df.unstack(level="lon")
cloud_df

cfc                                                              \
lon      -179.75   -179.25   -178.75   -178.25   -177.75   -177.25   -176.75   
lat                                                                            
-89.75  0.666667  0.650000  0.742690  0.729560  0.696429  0.668831  0.666667   
-89.25  0.748466  0.767857  0.766129  0.726316  0.769068  0.790744  0.733060   
-88.75  0.779156  0.806733  0.758178  0.769420  0.788750  0.766625  0.783432   
-88.25  0.744146  0.746690  0.739204  0.749376  0.757078  0.761116  0.751123   
-87.75  0.675506  0.678905  0.668647  0.698088  0.708861  0.693219  0.706967   
...          ...       ...       ...       ...       ...       ...       ...   
 87.75  0.555186  0.519005  0.531945  0.562544  0.534562  0.537164  0.553103   
 88.25  0.556514  0.574275  0.560034  0.584463  0.544348  0.561131  0.559586   
 88.75  0.618252  0.618090  0.588820  0.616751  0.606888  0.629911  0.618987   
 89.25  0.619748  0.650320  0.624738  0.648871  0.602105  0.639821  0.644841   
 89.75  0.653409  0.657343  0.692308  0.591716  0.647399  0.668874  0.638037   

                                      ...       time                        \
lon      -176.25   -175.75   -175.25  ...     175.25     175.75     176.25   
lat                                   ...                                    
-89.75  0.724359  0.657343  0.745665  ... 2016-12-01 2016-12-01 2016-12-01   
-89.25  0.745798  0.769080  0.753036  ... 2016-12-01 2016-12-01 2016-12-01   
-88.75  0.789474  0.765568  0.788820  ... 2016-12-01 2016-12-01 2016-12-01   
-88.25  0.737252  0.726407  0.729921  ... 2016-12-01 2016-12-01 2016-12-01   
-87.75  0.706767  0.715120  0.741007  ... 2016-12-01 2016-12-01 2016-12-01   
...          ...       ...       ...  ...        ...        ...        ...   
 87.75  0.543909  0.549855  0.537433  ... 2016-12-01 2016-12-01 2016-12-01   
 88.25  0.579041  0.576655  0.579577  ... 2016-12-01 2016-12-01 2016-12-01   
 88.75  0.605198  0.603034  0.611735  ... 2016-12-01 2016-12-01 2016-12-01   
 89.25  0.640756  0.639913  0.644681  ... 2016-12-01 2016-12-01 2016-12-01   
 89.75  0.628931  0.705882  0.662069  ... 2016-12-01 2016-12-01 2016-12-01   

                                                                          \
lon        176.75     177.25     177.75     178.25     178.75     179.25   
lat                                                                        
-89.75 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01   
-89.25 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01   
-88.75 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01   
-88.25 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01   
-87.75 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01   
...           ...        ...        ...        ...        ...        ...   
 87.75 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01   
 88.25 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01   
 88.75 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01   
 89.25 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01   
 89.75 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01 2016-12-01   

                   
lon        179.75  
lat                
-89.75 2016-12-01  
-89.25 2016-12-01  
-88.75 2016-12-01  
-88.25 2016-12-01  
-87.75 2016-12-01  
...           ...  
 87.75 2016-12-01  
 88.25 2016-12-01  
 88.75 2016-12-01  
 89.25 2016-12-01  
 89.75 2016-12-01  

[360 rows x 5760 columns]

This dataset is now fit to be visualised with plotly to create a 3D-surface plot. The x- and y-axes of this plot represent longitude and latitude. The z-axis shows the uncertainty, ahilst the actual cloud fraction is color-coded:

In [24]:
fig = go.Figure(
    data=[go.Surface(
        x=cloud_ds.lon.values,
        y=cloud_ds.lat.values,
        z=cloud_df[["cfc_unc"]].values,
        surfacecolor=cloud_df[["cfc"]].values,
        colorbar=dict(title="Cloud Fraction"),
         hovertemplate=
            "Longitude: %{x}<br>" +
            "Latitude: %{y}<br>" +
            "Uncertainty in %: %{z}<extra></extra>"  # Hoverinfo anpassen        
    )]
)

fig.update_layout(title=dict(text='Visualizing Cloud Uncertainties'), autosize=False,
                  width=500, height=500,
                  margin=dict(l=65, r=50, b=65, t=90))

fig.update_layout(
    scene=dict(
        xaxis_title="Longitude",
        yaxis_title="Latitude",
        zaxis_title="Uncertainty in %"
    )
)

fig.show()